In [ ]:
# imports
import mbuild as mb
import numpy as np
import bisect
import math
import random
from collections import deque, Counter
from scipy.spatial import KDTree
from gmso.core.forcefield import ForceField
import foyer
import forcefield_utilities as ffutils
from mbuild.lib.molecules import Ethane
from gmso.external.convert_mbuild import from_mbuild
from gmso.parameterization import apply
from gmso.formats.lammpsdata import write_lammpsdata
import sys
import re
from pathlib import Path
import gc
from scipy.spatial import KDTree


In [ ]:
# monte carlo set 

_BACKBONE = frozenset({"C1", "C2", "C3"})

BOND_LEN = 1.54   # A -- real C-C
KB = 1.987e-3     # kcal/mol/K


class MonteCarlo:

    def __init__(self, system, upper_root_atoms, lower_root_atoms,
                 amorphous_atoms, search_radius):
        self._system = system
        self._upper = sorted(upper_root_atoms)
        self._lower = sorted(lower_root_atoms)
        self._amor = sorted(amorphous_atoms)
        self._radius = search_radius

    # ── Atom classification ──────────────────────────────────────────────────

    def is_amorphous(self, i):
        idx = bisect.bisect_left(self._amor, i)
        return idx < len(self._amor) and self._amor[idx] == i

    def is_upper_root(self, i):
        idx = bisect.bisect_left(self._upper, i)
        return idx < len(self._upper) and self._upper[idx] == i

    def is_lower_root(self, i):
        idx = bisect.bisect_left(self._lower, i)
        return idx < len(self._lower) and self._lower[idx] == i

    def is_root(self, i):
        return self.is_upper_root(i) or self.is_lower_root(i)

    def face_of(self, atom_id):
        roots = self.segment_entry_points(atom_id)
        hi = any(self.is_upper_root(r) for r in roots)
        lo = any(self.is_lower_root(r) for r in roots)
        if hi and lo:
            return "both"
        if hi:
            return "upper"
        if lo:
            return "lower"
        return "none"

    # ── Graph traversal ──────────────────────────────────────────────────────

    def segment_entry_points(self, atom_id):
        entry = []
        visited = {atom_id}
        queue = []

        if self.is_root(atom_id):
            entry.append(atom_id)

        for nb in self._system.bonded_neighbors(atom_id):
            if self.is_amorphous(nb):
                queue.append(nb)
            elif self.is_root(nb):
                entry.append(nb)

        while queue:
            nxt = queue.pop()
            if nxt in visited:
                continue
            visited.add(nxt)
            if self.is_amorphous(nxt):
                for nb in self._system.bonded_neighbors(nxt):
                    if nb not in visited:
                        queue.append(nb)
            elif self.is_root(nxt):
                entry.append(nxt)

        return entry

    def segment_points(self, atom_id):
        pts = [atom_id]
        visited = {atom_id}
        queue = list(self._system.bonded_neighbors(atom_id))
        while queue:
            nxt = queue.pop()
            if nxt in visited:
                continue
            visited.add(nxt)
            if self.is_amorphous(nxt):
                pts.append(nxt)
                for nb in self._system.bonded_neighbors(nxt):
                    if nb not in visited:
                        queue.append(nb)
            elif self.is_root(nxt):
                pts.append(nxt)
        return pts

    def chain_atoms(self, atom_id):
        visited = {atom_id}
        queue = list(self._system.bonded_neighbors(atom_id))
        while queue:
            nxt = queue.pop()
            if nxt not in visited:
                visited.add(nxt)
                queue.extend(self._system.bonded_neighbors(nxt))
        return sorted(visited)

    def _connected(self, a, b):
        if a == b:
            return True
        seen, queue = {a}, deque([a])
        while queue:
            cur = queue.popleft()
            for nb in self._system.bonded_neighbors(cur):
                if nb == b:
                    return True
                if nb not in seen:
                    seen.add(nb)
                    queue.append(nb)
        return False

    def _mol_map(self):
        mol, comp_id = {}, 0
        for a in list(self._lower) + list(self._upper) + list(self._amor):
            if a in mol:
                continue
            for x in self.chain_atoms(a):
                mol[x] = comp_id
            mol[a] = comp_id
            comp_id += 1
        return mol, comp_id

    def molecule_count(self):
        _, n_comp = self._mol_map()
        return n_comp

    def count_rings(self):
        mol, n_comp = self._mol_map()
        v = len(mol)
        e = sum(len(self._system.bonded_neighbors(a)) for a in mol) // 2
        return e - v + n_comp

    # ── Geometry helpers ─────────────────────────────────────────────────────

    def _dvec(self, a, b):
        s = self._system
        try:
            return np.asarray(s.bond_image(s[a], s[b]), dtype=float)
        except AttributeError:
            return np.array(s[b], dtype=float) - np.array(s[a], dtype=float)

    def _dist(self, a, b):
        return float(np.linalg.norm(self._dvec(a, b)))

    def _metropolis(self, d_new, d_old, T, k_eff=1.0):
        if T is None:
            return True
        dE = k_eff * ((d_new - BOND_LEN) ** 2)
        if d_old is not None:
            dE -= k_eff * ((d_old - BOND_LEN) ** 2)
        if dE <= 0:
            return True
        return random.random() <= math.exp(-dE / (KB * T))

    # ── Moves ────────────────────────────────────────────────────────────────

    def end_bridge(self, max_attempts=10_000, T=None, quiet=False):
        s = self._system

        def amorphous_only(lst):
            return [x for x in lst if self.is_amorphous(x)]

        chain_ends = [e for e in self._amor
                      if len(s.bonded_neighbors(e)) == 1]
        if not chain_ends:
            if not quiet:
                print("!! end_bridge: no amorphous chain ends found")
            return False

        tail_ends = [
            e for e in chain_ends
            if not self.is_root(e)
            and len(self.segment_entry_points(e)) == 1
            and s._particles[e].name in _BACKBONE
        ]
        if not tail_ends:
            if not quiet:
                names = dict(Counter(s._particles[e].name for e in chain_ends))
                print(f"!! end_bridge: no valid attacker tail ends "
                      f"(end-atom names: {names})")
            return False

        mol_map, _ = self._mol_map()

        stats = Counter()
        a_tried = Counter()
        attempt = 0

        while attempt < max_attempts:
            random.shuffle(tail_ends)

            for A in tail_ends:
                attempt += 1
                a_tried[A] += 1
                if attempt > max_attempts:
                    break

                excl = set(self.segment_points(A))
                neighbors = [x for x in amorphous_only(
                                 s.find_atoms_within_cutoff(A, self._radius))
                             if x not in excl]
                if not neighbors:
                    stats['no_neighbors'] += 1
                    continue

                bridge_neighbors = [
                    x for x in neighbors
                    if s._particles[x].name in _BACKBONE
                    and len(s.bonded_neighbors(x)) == 2
                    and not self.is_root(x)
                    and not any(self.is_root(nb) for nb in s.bonded_neighbors(x))
                    and len(self.segment_entry_points(x)) == 2
                    and self._dist(A, x) < self._radius
                ]
                if not bridge_neighbors:
                    stats['no_T1'] += 1
                    continue
                T1 = random.choice(bridge_neighbors)

                T2_candidates = [
                    nb for nb in s.bonded_neighbors(T1)
                    if s._particles[nb].name in _BACKBONE
                    and not self.is_root(nb)
                    and any(x != T1 for x in s.bonded_neighbors(nb))
                ]
                if not T2_candidates:
                    stats['no_T2'] += 1
                    continue
                T2 = random.choice(T2_candidates)

                d_new = self._dist(A, T1)
                d_old = self._dist(T1, T2)
                same_mol = (mol_map.get(A) == mol_map.get(T1))

                s.delete_bond(T1, T2)

                if self._connected(A, T1):
                    s.add_bond(T1, T2)
                    stats['would_cyclize'] += 1
                    continue

                s.add_bond(A, T1)

                def revert(reason):
                    s.delete_bond(A, T1)
                    s.add_bond(T1, T2)
                    stats[reason] += 1

                if len(self.segment_entry_points(T2)) == 0:
                    revert('T2_orphaned')
                    continue

                t2_reachable = self._connected(A, T2)
                if same_mol and not t2_reachable:
                    revert('would_split')
                    continue
                if (not same_mol) and t2_reachable:
                    revert('would_merge')
                    continue

                excl_T2 = set(self.segment_points(T2))
                bk_nb = [x for x in amorphous_only(
                             s.find_atoms_within_cutoff(T2, self._radius))
                         if x not in excl_T2]
                if not bk_nb:
                    revert('no_backward_pool')
                    continue

                if not self._metropolis(d_new, d_old, T):
                    revert('metropolis')
                    continue

                s.assign_molecules_ids()
                return True

            if stats and set(stats) <= {'no_neighbors', 'no_T1'}:
                break

        if not quiet:
            print(f"!! end_bridge: failed after {attempt} attempts: {dict(stats)}")
            print(f"   A sampled: {len(a_tried)} distinct of {len(tail_ends)} pool")
        return False

    def tail_reconnect(self, T=None, quiet=True, min_molecules=2):
        s = self._system

        if self.molecule_count() <= min_molecules:
            if not quiet:
                print(f"  tail_reconnect: at {min_molecules} molecules, every "
                      f"remaining weld would merge or cyclize -- stopping")
            return False

        pool = [e for e in self._amor
                if len(s.bonded_neighbors(e)) == 1
                and not self.is_root(e)
                and len(self.segment_entry_points(e)) == 1
                and s._particles[e].name in _BACKBONE]
        if not pool:
            return False

        faces = {e: self.face_of(e) for e in pool}
        upper_total = sum(1 for f in faces.values() if f == "upper")
        lower_total = sum(1 for f in faces.values() if f == "lower")
        if upper_total < 1 or lower_total < 1:
            return False

        mol_map, _ = self._mol_map()

        attackers = pool[:]
        random.shuffle(attackers)
        for A in attackers:
            seg_A = set(self.segment_points(A))
            face_A = faces[A]

            candidates = []
            for B in pool:
                if B == A or B in seg_A:
                    continue
                if self._dist(A, B) >= self._radius:
                    continue
                if mol_map.get(A) == mol_map.get(B):
                    continue
                face_B = faces[B]
                if upper_total - (face_A == "upper") - (face_B == "upper") < 1:
                    continue
                if lower_total - (face_A == "lower") - (face_B == "lower") < 1:
                    continue
                candidates.append(B)
            if not candidates:
                continue

            B = random.choice(candidates)
            d_new = self._dist(A, B)
            s.add_bond(A, B)

            if not self._metropolis(d_new, None, T):
                s.delete_bond(A, B)
                continue
            if len(self.segment_entry_points(A)) == 0:
                s.delete_bond(A, B)
                continue

            s.assign_molecules_ids()
            return True

        if not quiet:
            print(f"!! tail_reconnect: no valid pair "
                  f"(pool {len(pool)}, upper {upper_total}, lower {lower_total})")
        return False

    # ── Segment classification ───────────────────────────────────────────────

    def _classify_segments(self):
        """
        loops   -- both crystal-root connections on the same face
        bridges -- root connections on opposite faces
        tails   -- exactly one crystal-root connection (free end)
        """
        loops, bridges, tails = [], [], []
        visited_roots = set()
        visited_amor = set()

        for root_i in self._lower + self._upper:
            if root_i in visited_roots:
                continue
            visited_roots.add(root_i)

            neighbors = self._system.bonded_neighbors(root_i)
            if len(neighbors) < 2:
                print(f"  Warning: root {root_i + 1} has < 2 neighbours")
                tails.append([root_i])
                continue

            for amor_nb in neighbors:
                if not self.is_amorphous(amor_nb) or amor_nb in visited_amor:
                    continue

                roots_of_seg = self.segment_entry_points(amor_nb)
                seg_pts = self.segment_points(amor_nb)

                for p in seg_pts:
                    if self.is_amorphous(p):
                        visited_amor.add(p)

                if not roots_of_seg:
                    print(f"  Warning: floating fragment at atom {amor_nb + 1}")
                    continue

                if len(roots_of_seg) == 1:
                    tails.append(seg_pts)
                else:
                    if len(roots_of_seg) > 2:
                        print(f"  Warning: segment at {amor_nb + 1} has "
                              f"{len(roots_of_seg)} entry points (branched?)")
                    visited_roots.update(roots_of_seg)
                    same_face = (self.is_lower_root(roots_of_seg[0])
                                 == self.is_lower_root(roots_of_seg[1]))
                    (loops if same_face else bridges).append(seg_pts)

        return loops, bridges, tails

    def count_segments(self, out_path="segments.txt"):
        loops, bridges, tails = self._classify_segments()

        if out_path:
            with open(out_path, "w") as f:
                for label, group in (("Tails", tails), ("Bridges", bridges),
                                     ("Loops", loops)):
                    f.write(f"{label} ({len(group)}):\n")
                    for seg in group:
                        f.write("{" + ", ".join(str(i + 1) for i in seg) + "}\n")
                    f.write("\n")

        if len(tails) % 2:
            print(f"  Warning: odd tail count ({len(tails)}) -- "
                  f"broken-chain count is approximate")

        n_broken = len(tails) // 2
        total = n_broken + len(bridges) + len(loops)
        n_stem = len(self._lower)
        if len(self._upper) != n_stem:
            print(f"  Warning: {len(self._lower)} lower vs {len(self._upper)} "
                  f"upper roots -- each stem should have one of each")
        n_root = len(self._lower) + len(self._upper)
        n_mol = self.molecule_count()
        n_ring = self.count_rings()

        print(f"  Total chains : {total}")
        print(f"  |- Bridges   : {len(bridges)}")
        print(f"  |- Loops     : {len(loops)}")
        print(f"  '- Broken    : {n_broken}  ({len(tails)} tail segments)")
        print(f"  Stems        : {n_stem}   Roots : {n_root}")

        expected_sections = n_stem - n_mol
        got = len(bridges) + len(loops)
        if got != expected_sections:
            print(f"  Warning: {got} sections, expected {expected_sections} "
                  f"for {n_mol} linear molecules over {n_stem} stems "
                  f"(excess {got - expected_sections}, rings reported {n_ring})")
        if len(tails) != 2 * n_mol:
            print(f"  Warning: {len(tails)} tails, expected {2 * n_mol} for "
                  f"{n_mol} linear molecules -- ring present?")
        if n_ring:
            print(f"  Warning: {n_ring} ring(s) present. Cyclic molecules have "
                  f"zero tails and cannot be compared against Adhikari-"
                  f"Muthukumar statistics (Z carries a g_tail^2 factor).")

        if n_mol and not n_ring:
            per_chain_stems = n_stem / n_mol
            print(f"  f_tie        : "
                  f"{len(bridges) / n_mol / (per_chain_stems + 1):.4f} per chain"
                  f"   (theory n_stem = {per_chain_stems:.0f})")

        return loops, bridges, tails

In [ ]:
import math
import random

import numpy as np
import mbuild as mb


# -- Constants -----------------------------------------------------------------

A_CELL, B_CELL, C_CELL = 7.417, 4.945, 2.534      # Angstrom
M_CH2 = 14.027                                     # amu

alpha = 1.208435          # backbone C-C-C angle, rad
phi = 0.733               # setting angle, rad
lbond = 1.54              # Angstrom

la, lb, lc = A_CELL / 10, B_CELL / 10, C_CELL / 10      # nm

dx = lbond * np.cos(phi) * np.sin(alpha / 2) / 2 / 10   # nm
dy = lbond * np.sin(alpha / 2) * np.sin(phi) / 2 / 10   # nm
dz = lc / 2                                             # nm, rise per carbon

NX, NY = 14, 20
N_REPEAT = 202            # 2*N_REPEAT carbons per stem (must be even)
SEED = 2

LX, LY, LZ = NX * la, NY * lb, 2 * N_REPEAT * dz

AMOR_LO_FRAC, AMOR_HI_FRAC = 0.35, 0.65
RHO_A_NOMINAL = 0.855                      # g/cm3
RHO_A_TARGET = 0.910                       # g/cm3
N_TAILS_TARGET = 2
MU_TIE = 2.0                               # kcal/mol
WELD_T = 450.0                             # K
WELD_CUTOFF_0 = 0.6                        # nm
KB = 1.987e-3                              # kcal/mol/K

AMU_PER_NM3_TO_G_PER_CM3 = 1.66054e-3

M_UNIT = M_CH2
UNIT_RISE = dz

_BACKBONE = frozenset({"C2", "C3"})
_PENDANT = frozenset()


def amu_per_nm3_to_g_per_cm3(x):
    return x * AMU_PER_NM3_TO_G_PER_CM3


def crystal_density():
    """g/cm3 from the lattice: 4 CH2 per orthorhombic cell."""
    v_nm3 = (A_CELL / 10) * (B_CELL / 10) * (C_CELL / 10)
    return amu_per_nm3_to_g_per_cm3(4 * M_CH2 / v_nm3)


def chi_to_window(chi, rho_c=None, rho_a=RHO_A_NOMINAL):
    """Window fractions giving a target mass crystallinity."""
    rho_c = crystal_density() if rho_c is None else rho_c
    ratio = (1.0 / chi - 1.0) * rho_c / rho_a
    f = ratio / (1.0 + ratio)
    return 0.5 - f / 2, 0.5 + f / 2


# -- Chain builder -------------------------------------------------------------

def build_chain(cx, cy, n_repeat, z_offset=0.0, start_sign=1, tilt=+1,
                periodic_z=False, flip_z=False):
    chain = mb.Compound()
    c_list = []
    total_atoms = 2 * n_repeat
    if total_atoms % 2:
        raise ValueError("need an even carbon count so C2/C3 alternation closes "
                         "across the periodic bond")

    for i in range(total_atoms):
        sign = start_sign * (+1 if i % 2 == 0 else -1)
        z = z_offset + ((total_atoms - 1 - i) if flip_z else i) * dz
        c_a = mb.Compound(name=("C2" if i % 2 == 0 else "C3"),
                          pos=[cx + sign * dx, cy + tilt * sign * dy, z])
        c_a.element = "C"
        chain.add(c_a)
        c_list.append(c_a)
        if i > 0:
            chain.add_bond((c_list[-2], c_a))

    if periodic_z and len(c_list) > 1:
        # Bond through the periodic z boundary; the writer must emit image flags.
        chain.add_bond((c_list[-1], c_list[0]))
    return chain


def build_pe_crystal(nx, ny, n_repeat, periodic_z=True):
    system = mb.Compound()
    for ix in range(nx):
        for iy in range(ny):
            system.add(build_chain(cx=(ix + 0.25) * la, cy=(iy + 0.25) * lb,
                                   n_repeat=n_repeat, tilt=+1,
                                   periodic_z=periodic_z, flip_z=False))
            system.add(build_chain(cx=(ix + 0.75) * la, cy=(iy + 0.75) * lb,
                                   n_repeat=n_repeat, tilt=-1,
                                   periodic_z=periodic_z, flip_z=True))
    return system


# -- Topology helpers ----------------------------------------------------------

def adjacency(system):
    adj = {p: set() for p in system.particles()}
    for p1, p2 in system.bonds():
        adj[p1].add(p2)
        adj[p2].add(p1)
    return adj


def backbone_neighbors(p, adj):
    return [q for q in adj[p] if q.name not in _PENDANT]


def find_clusters(system, adj=None):
    adj = adj if adj is not None else adjacency(system)
    visited, clusters = set(), []
    for p in adj:
        if p in visited:
            continue
        cluster, queue = set(), [p]
        while queue:
            node = queue.pop()
            if node in visited:
                continue
            visited.add(node)
            cluster.add(node)
            queue.extend(adj[node] - visited)
        clusters.append(cluster)
    return clusters


def in_window(p, z_lo, z_hi):
    return z_lo <= p.pos[2] <= z_hi


def is_cuttable(p1, p2):
    return p1.name in _BACKBONE and p2.name in _BACKBONE


def _pos_key(p):
    """Deterministic sort key; Compounds hash by identity, so set order varies."""
    return (round(float(p.pos[2]), 6),
            round(float(p.pos[0]), 6),
            round(float(p.pos[1]), 6),
            p.name)


def _bond_key(bond):
    p1, p2 = bond
    k1, k2 = _pos_key(p1), _pos_key(p2)
    return (k1, k2) if k1 <= k2 else (k2, k1)


def window_mass(system, z_lo, z_hi):
    return sum(M_CH2 for p in system.particles() if in_window(p, z_lo, z_hi))


def total_mass(system):
    return sum(M_CH2 for _ in system.particles())


def amorphous_density(system, z_lo, z_hi, lx=None, ly=None):
    lx = LX if lx is None else lx
    ly = LY if ly is None else ly
    vol = lx * ly * (z_hi - z_lo)                     # nm^3
    return amu_per_nm3_to_g_per_cm3(window_mass(system, z_lo, z_hi) / vol)


def mass_crystallinity(system, z_lo, z_hi):
    m_tot = total_mass(system)
    m_amor = window_mass(system, z_lo, z_hi)
    return (m_tot - m_amor) / m_tot if m_tot else 0.0


# -- Calibration ---------------------------------------------------------------

def rho_per_unit(z_lo, z_hi, lx=None, ly=None):
    """Window density change per CH2 removed, g/cm3 (at build time)."""
    lx = LX if lx is None else lx
    ly = LY if ly is None else ly
    return amu_per_nm3_to_g_per_cm3(M_UNIT / (lx * ly * (z_hi - z_lo)))


def units_for_delta(drho, z_lo, z_hi):
    """CH2 sites to add (drho < 0) or drop (drho > 0) to move rho_a by drho."""
    return int(round(drho / rho_per_unit(z_lo, z_hi)))


def n_remove_for(rho_want, runs):
    """Interpolate a cut count from [(n_remove, rho_after_min), ...]."""
    if len(runs) < 2:
        raise ValueError("need at least two (n_remove, rho) points to fit")
    (n1, r1), (n2, r2) = runs[0], runs[-1]
    if n2 == n1:
        raise ValueError("the two calibration points share a cut count")
    slope = (r2 - r1) / (n2 - n1)
    return int(round(n1 + (rho_want - r1) / slope))


# -- Cutting -------------------------------------------------------------------

def remove_floating(system, z_lo, z_hi, nmin=1):
    """Delete every component lying wholly inside the window.

    Returns (n_atoms, mass, max_z_span)."""
    doomed, span_max = [], 0.0
    for cluster in find_clusters(system):
        if len(cluster) < nmin:
            continue
        if all(in_window(p, z_lo, z_hi) for p in cluster):
            zs = [p.pos[2] for p in cluster]
            span_max = max(span_max, max(zs) - min(zs))
            doomed.extend(cluster)
    if not doomed:
        return 0, 0.0, 0.0
    mass = len(doomed) * M_CH2
    # Single remove() call; per-atom removal is quadratic in mbuild.
    try:
        system.remove(doomed, reset_labels=False)
    except TypeError:
        system.remove(doomed)
    return len(doomed), mass, span_max


def stem_cuttable_bonds(cluster, adj, z_lo, z_hi):
    """Cuttable bonds of one stem lying wholly inside the window, ordered along z."""
    out, seen = [], set()
    for p1 in cluster:
        for p2 in adj[p1]:
            if not is_cuttable(p1, p2):
                continue
            if not (in_window(p1, z_lo, z_hi) and in_window(p2, z_lo, z_hi)):
                continue
            k = _bond_key((p1, p2))
            if k in seen:
                continue
            seen.add(k)
            out.append((p1, p2))
    out.sort(key=lambda bd: (round(0.5 * (bd[0].pos[2] + bd[1].pos[2]), 6),
                             _bond_key(bd)))
    return out


def place_excision(m, quota, rng):
    """Choose one (start_index, span) excision among m in-window bonds."""
    if quota <= 0 or m - 1 < quota:
        return None
    return rng.randint(0, m - 1 - quota), quota


def cut_to_density(system, z_lo, z_hi, rho_target=RHO_A_TARGET, rho_c=None,
                   seed=SEED, max_span_frac=0.20, verbose=True,
                   n_remove=None):
    """Excise CH2 sites from the window.

    n_remove=None derives the count from rho_target; an int uses that count.
    Returns (n_cuts, max_span, n_remove)."""
    rng = random.Random(seed)
    rho_c = crystal_density() if rho_c is None else rho_c

    depth = z_hi - z_lo
    vol = LX * LY * depth
    m_now = window_mass(system, z_lo, z_hi)

    if n_remove is None:
        m_target = rho_target * vol / AMU_PER_NM3_TO_G_PER_CM3
        n_remove = int(round((m_now - m_target) / M_UNIT))
        mode = f"auto, target {rho_target:.3f}"
    else:
        n_remove = int(n_remove)
        mode = "manual"

    rho_build = amu_per_nm3_to_g_per_cm3((m_now - n_remove * M_UNIT) / vol)

    max_span = max(1, int(max_span_frac * depth / UNIT_RISE))

    adj = adjacency(system)
    clusters = find_clusters(system, adj)
    clusters.sort(key=lambda cl: min(_pos_key(p) for p in cl))
    pools = [stem_cuttable_bonds(cl, adj, z_lo, z_hi) for cl in clusters]
    live = [i for i, p in enumerate(pools) if len(p) >= 2]
    if not live:
        raise RuntimeError("no stem has two cuttable bonds inside the window")

    if verbose:
        print(f"  window depth {depth*10:.1f} A "
              f"({depth/UNIT_RISE:.1f} sites deep)")
        print(f"  rho_a before {amorphous_density(system, z_lo, z_hi):.4f} "
              f"-> as-built {rho_build:.4f} g/cm3  [{mode}]")
        print(f"  sensitivity {rho_per_unit(z_lo, z_hi)*1e4:.3f}e-4 "
              f"g/cm3 per CH2")
        print(f"  removing {n_remove} CH2 over {len(live)} stems "
              f"({n_remove/len(live):.2f} per stem, "
              f"{n_remove/len(live)*UNIT_RISE*10:.1f} A gap)")

    if n_remove <= 0:
        if verbose:
            print("  nothing to remove; window is already at or below target")
        return 0, 0.0, n_remove

    # Every periodic stem needs at least one excision or it stays a ring.
    if n_remove < len(live):
        raise RuntimeError(
            f"n_remove = {n_remove} is below the {len(live)} live stems, so some "
            f"stems would get no excision and keep their periodic ring.  Widen "
            f"the window, lower rho_target, or drop periodic_z.")

    base, extra = divmod(n_remove, len(live))
    bonus = set(rng.sample(live, extra))
    quotas = {i: base + (1 if i in bonus else 0) for i in live}

    q_max = max(quotas.values())
    if q_max > max_span:
        print(f"  WARNING: this cut count needs {q_max} sites from a stem "
              f"({q_max*UNIT_RISE*10:.1f} A hole), above the {max_span}-site cap. "
              f"A stem cannot be cut more than twice without merging its holes; "
              f"deepen the window or add stems.")

    cuts = []
    for i in live:
        exc = place_excision(len(pools[i]), quotas[i], rng)
        if exc is None:
            raise RuntimeError(
                f"stem {i} has {len(pools[i])} cuttable bonds in the window but "
                f"must give up {quotas[i]} sites; deepen the window")
        j, k = exc
        cuts.append(pools[i][j])
        cuts.append(pools[i][j + k])

    for p1, p2 in cuts:
        system.remove_bond((p1, p2))

    n_gone, m_gone, span_max = remove_floating(system, z_lo, z_hi)

    if verbose:
        rho = amorphous_density(system, z_lo, z_hi)
        dev = rho - rho_build
        n_short = n_remove - int(round(m_gone / M_UNIT))
        print(f"  {len(cuts)} cuts in {len(cuts)//2} excisions; "
              f"{n_gone} atoms ({m_gone:.0f} amu) removed")
        if n_short:
            print(f"  NOTE: {n_short} budgeted sites were not deleted -- those "
                  f"excisions straddle a window edge and survive "
                  f"remove_floating's 'wholly inside' test")
        print(f"  longest deleted fragment spans {span_max*10:.1f} A "
              f"({span_max/depth*100:.1f}% of the window)")
        print(f"  rho_a = {rho:.4f} g/cm3 ({abs(dev):.4f} "
              f"{'above' if dev > 0 else 'below'} as-built, "
              f"{abs(dev)/rho_build*100:.2f}%)")
        if span_max > max_span_frac * depth:
            print(f"  WARNING: a deleted fragment spans more than "
                  f"{max_span_frac*100:.0f}% of the window.  That is a channel, "
                  f"and no barostat will close it -- it runs along z.")
    return len(cuts), span_max, n_remove


# -- Free ends and face classification -----------------------------------------

def free_ends(system, adj=None):
    """Backbone atoms with fewer than two backbone neighbours."""
    adj = adj if adj is not None else adjacency(system)
    return [p for p in adj
            if p.name in _BACKBONE and len(backbone_neighbors(p, adj)) < 2]


def face_of_end(end, adj, z_lo, z_hi):
    """Walk from a stub until it leaves the window: 'lower', 'upper' or 'none'."""
    seen, cur = {end}, end
    while True:
        nbrs = [p for p in backbone_neighbors(cur, adj) if p not in seen]
        if not nbrs:
            return "none"
        cur = nbrs[0]
        seen.add(cur)
        if cur.pos[2] < z_lo:
            return "lower"
        if cur.pos[2] > z_hi:
            return "upper"


def _mi_dist(p1, p2):
    """Minimum-image distance in x and y."""
    d = np.array(p2.pos, dtype=float) - np.array(p1.pos, dtype=float)
    d[0] -= LX * round(d[0] / LX)
    d[1] -= LY * round(d[1] / LY)
    return float(np.linalg.norm(d))


# -- Reporting -----------------------------------------------------------------

def report(system, z_lo, z_hi, label=""):
    adj = adjacency(system)
    n_atoms = len(adj)
    n_bonds = sum(len(v) for v in adj.values()) // 2
    clusters = find_clusters(system, adj)
    ends = free_ends(system, adj)
    faces = {e: face_of_end(e, adj, z_lo, z_hi) for e in ends}

    rho = amu_per_nm3_to_g_per_cm3(n_atoms * M_CH2 / (LX * LY * LZ))
    chi = mass_crystallinity(system, z_lo, z_hi)

    n_ring = n_bonds - n_atoms + len(clusters)    # cyclomatic number

    n_lo = sum(1 for e in ends if faces[e] == "lower")
    n_up = sum(1 for e in ends if faces[e] == "upper")
    n_fl = sum(1 for e in ends if faces[e] == "none")

    print(f"-- {label} --")
    print(f"  atoms {n_atoms:,}   bonds {n_bonds:,}   molecules {len(clusters)}"
          f"   rings {n_ring}")
    print(f"  stubs {len(ends)}  (lower {n_lo}, upper {n_up}, floating {n_fl})")
    print(f"  rho_total {rho:.4f} g/cm3   "
          f"rho_amorphous {amorphous_density(system, z_lo, z_hi):.4f} g/cm3   "
          f"chi_mass {chi:.4f}")

    if n_lo != n_up:
        print(f"  WARNING: {n_lo} lower stubs vs {n_up} upper stubs -- a stem was "
              f"cut more than once, or a fragment left with unpaired ends")
    if n_fl:
        print(f"  WARNING: {n_fl} stubs on fragments that never leave the window "
              f"-- remove_floating missed them")
    if ends and (n_lo == 0 or n_up == 0):
        print(f"  WARNING: no stubs anchored to one face -- weld_paths cannot "
              f"form loops there and will stall")
    if n_ring and ends:
        print(f"  WARNING: {n_ring} ring(s) survived cutting. Cyclic molecules "
              f"have zero tails and cannot be compared against Adhikari-"
              f"Muthukumar statistics; every stem needs one excision")
    return {"atoms": n_atoms, "bonds": n_bonds, "molecules": len(clusters),
            "rings": n_ring, "stubs": len(ends), "lower": n_lo, "upper": n_up,
            "floating": n_fl,
            "rho_a": amorphous_density(system, z_lo, z_hi), "chi": chi}


from math import gcd
# -- Interface orientation -----------------------------------------------------

HKL = (2, 0, 1)    # (h0l) interface plane; (0, 0, 1) is the untilted build

def interface_frame(hkl, nx, ny, n_repeat):
    """Lab frame with the (h0l) normal along z.

    Returns (R, (lx, ly, lz, xz), cells along crystal a)."""
    h, k, l = hkl
    if k != 0:
        raise NotImplementedError("only (h0l) planes; for (0kl) swap a and b")
    if l == 0:
        raise ValueError("l = 0 puts the chain axis in the interface plane; no "
                         "stem crosses the window, so there is nothing to cut")
    g = gcd(abs(h), abs(l))
    G = np.array([h / la, 0.0, l / lc])
    ez = G / np.linalg.norm(G)
    ey = np.array([0.0, 1.0, 0.0])
    ex = np.cross(ey, ez)
    R = np.vstack([ex, ey, ez])

    A = nx * np.array([l * la, 0.0, -h * lc]) / g
    B = np.array([0.0, ny * lb, 0.0])
    C = np.array([0.0, 0.0, n_repeat * lc])
    A, B, C = R @ A, R @ B, R @ C
    assert abs(A[1]) < 1e-9 and abs(A[2]) < 1e-9 and abs(C[1]) < 1e-9

    lx, ly, lz, xz = A[0], B[1], C[2], C[0]
    xz -= lx * round(xz / lx)    # reduce tilt; C and C - n*A span the same lattice
    return R, (lx, ly, lz, xz), nx * l // g


def tilt_angle(hkl):
    h, _, l = hkl
    return np.degrees(np.arctan2(h * lc, l * la))


def wrap(xyz, box):
    lx, ly, lz, xz = box
    xyz = xyz.copy()
    n = np.floor(xyz[:, 2] / lz)
    xyz[:, 2] -= n * lz
    xyz[:, 0] -= n * xz
    xyz[:, 0] -= lx * np.floor(xyz[:, 0] / lx)
    xyz[:, 1] -= ly * np.floor(xyz[:, 1] / ly)
    return xyz


def build_pe_crystal_hkl(hkl, nx, ny, n_repeat, periodic_z=True):
    R, box, na = interface_frame(hkl, nx, ny, n_repeat)
    system = build_pe_crystal(na, ny, n_repeat, periodic_z=periodic_z)
    system.xyz = wrap(system.xyz @ R.T, box)
    return system, box


# -- Driver --------------------------------------------------------------------

N_REMOVE = 560    # int for manual control, None to derive from RHO_A_TARGET


random.seed(SEED)
np.random.seed(SEED)

print(f"orthorhombic PE  a={A_CELL} b={B_CELL} c={C_CELL} A   "
      f"V={A_CELL*B_CELL*C_CELL:.2f} A^3")
print(f"  rho_c = {crystal_density():.4f} g/cm3 (expt 1.00)")
print(f"  area/chain = {LX*LY/(NX*NY*2)*100:.2f} A^2")
print(f"  box {LX*10:.2f} x {LY*10:.2f} x {LZ*10:.2f} A")

system, (LX, LY, LZ, XZ) = build_pe_crystal_hkl(HKL, NX, NY, N_REPEAT)
n_stem = 2 * NY * (NX * HKL[2] // math.gcd(HKL[0], HKL[2]))

n_atoms = sum(1 for _ in system.particles())
print(f"built {n_stem} stems, {n_atoms:,} carbons")
print(f"n_stem = {n_stem}  -> use this in the theory script, NOT Belin's 70")

z_amor_lo, z_amor_hi = AMOR_LO_FRAC * LZ, AMOR_HI_FRAC * LZ

report(system, z_amor_lo, z_amor_hi, "after build")
print()
n_cuts, span_max, n_used = cut_to_density(
    system, z_amor_lo, z_amor_hi, RHO_A_TARGET, n_remove=N_REMOVE)
print()
report(system, z_amor_lo, z_amor_hi, "after cutting")
print()
print(f"cut count used: {n_used}  "
      f"(set N_REMOVE = {n_used} to reproduce, adjust with units_for_delta)")

orthorhombic PE  a=7.417 b=4.945 c=2.534 A   V=92.94 A^3
  rho_c = 1.0025 g/cm3 (expt 1.00)
  area/chain = 18.34 A^2
  box 103.84 x 98.90 x 511.87 A
built 560 stems, 226,240 carbons
n_stem = 560  -> use this in the theory script, NOT Belin's 70
-- after build --
  atoms 226,240   bonds 226,240   molecules 560   rings 560
  stubs 0  (lower 0, upper 0, floating 0)
  rho_total 1.0025 g/cm3   rho_amorphous 1.0008 g/cm3   chi_mass 0.7005

  window depth 126.8 A (100.1 sites deep)
  rho_a before 1.0008 -> as-built 0.9925 g/cm3  [manual]
  sensitivity 0.148e-4 g/cm3 per CH2
  removing 560 CH2 over 560 stems (1.00 per stem, 1.3 A gap)
  1120 cuts in 560 excisions; 560 atoms (7855 amu) removed
  longest deleted fragment spans 0.0 A (0.0% of the window)
  rho_a = 0.9925 g/cm3 (0.0000 below as-built, 0.00%)

-- after cutting --
  atoms 225,680   bonds 225,120   molecules 560   rings 0
  stubs 1120  (lower 560, upper 560, floating 0)
  rho_total 1.0000 g/cm3   rho_amorphous 0.9925 g/cm3   chi_mass

In [50]:
system.visualize()

3Dmol.js failed to load for some reason. Please check your browser console for error messages.

In [ ]:
class _Particle:
    """Minimal stand-in for an mBuild Particle used only inside MDSystem."""

    __slots__ = ("name", "pos")

    def __init__(self, name: str, pos_nm: np.ndarray):
        self.name = name
        self.pos = np.asarray(pos_nm, dtype=float)  # nm, matches mBuild convention


class MDSystem:
    """Bond/geometry bookkeeping for a large PE system."""

    # Always degree-1 by design -> never counted as chain termini.
    _PENDANT_NAMES = frozenset({"H", "H_end"})

    # Backbone carbons that receive 2 H each. "C" is the capped terminus.
    _CC_NAMES = frozenset({"C", "C2", "C3"})

    _CH_BOND = 1.09           # C-H bond length, Å

    _ELEMENT_MAP = {
        "C": "C", "C2": "C", "C3": "C",
        "H": "H", "H_end": "H",
    }

    def __init__(self, mb_system, box_Å):
        parts = list(mb_system.particles())
        self._n = len(parts)
        self._cap = max(16, 2 * self._n)

        self._pos_buf = np.zeros((self._cap, 3), dtype=float)
        self._pos_buf[: self._n] = (
            np.asarray([p.pos for p in parts], dtype=float) * 10.0  # nm -> Å
        )

        self._box = np.asarray(box_Å, dtype=float)

        idx = {p: i for i, p in enumerate(parts)}
        self._neighbors = {i: [] for i in range(self._n)}
        for p1, p2 in mb_system.bonds():
            i, j = idx.get(p1), idx.get(p2)
            if i is None or j is None:
                continue
            if j not in self._neighbors[i]:
                self._neighbors[i].append(j)
            if i not in self._neighbors[j]:
                self._neighbors[j].append(i)

        self._particles = [
            _Particle(p.name, self._pos_buf[i] / 10.0) for i, p in enumerate(parts)
        ]
        del parts, idx

        self._kdtree = None
        self._kdtree_dirty = True

    # ── Internal helpers ──────────────────────────────────────────────────

    @property
    def _positions(self):
        """Live (n, 3) view of the Å buffer."""
        return self._pos_buf[: self._n]

    def _grow(self, extra=1):
        need = self._n + extra
        if need <= self._cap:
            return
        while self._cap < need:
            self._cap *= 2
        buf = np.zeros((self._cap, 3), dtype=float)
        buf[: self._n] = self._pos_buf[: self._n]
        self._pos_buf = buf

    @property
    def kdtree(self):
        """Rebuilt lazily on the first query after a mutation."""
        if self._kdtree_dirty or self._kdtree is None:
            self._kdtree = KDTree(self._positions)
            self._kdtree_dirty = False
        return self._kdtree

    # ── Core accessors ────────────────────────────────────────────────────

    def __getitem__(self, i):
        return self._positions[i]

    def bonded_neighbors(self, i):
        return list(self._neighbors[i])

    def find_atoms_within_cutoff(self, i, r):
        idxs = self.kdtree.query_ball_point(self._positions[i], r)
        return [j for j in idxs if j != i]

    def bond_image(self, a, b):
        pa = self._positions[a] if isinstance(a, (int, np.integer)) else np.asarray(a)
        pb = self._positions[b] if isinstance(b, (int, np.integer)) else np.asarray(b)
        dr = pb - pa
        dr -= self._box * np.round(dr / self._box)
        return dr

    # ── Bond editing ──────────────────────────────────────────────────────

    def add_bond(self, i, j):
        if j not in self._neighbors[i]:
            self._neighbors[i].append(j)
        if i not in self._neighbors[j]:
            self._neighbors[j].append(i)

    def delete_bond(self, i, j):
        self._neighbors[i] = [x for x in self._neighbors[i] if x != j]
        self._neighbors[j] = [x for x in self._neighbors[j] if x != i]

    # ── Atom addition ─────────────────────────────────────────────────────

    def add_particle(self, name: str, position_Å) -> int:
        """Append an atom and return its index. O(1) amortized."""
        pos_Å = np.asarray(position_Å, dtype=float)
        self._grow()

        i = self._n
        self._pos_buf[i] = pos_Å
        self._particles.append(_Particle(name, pos_Å / 10.0))
        self._neighbors[i] = []
        self._n += 1
        self._kdtree_dirty = True
        return i

    # ── Chain-end detection ───────────────────────────────────────────────

    def end_atoms(self):
        """Degree-1 backbone carbons (pendant H excluded)."""
        return [
            i
            for i in range(self._n)
            if len(self._neighbors[i]) == 1
            and self._particles[i].name not in self._PENDANT_NAMES
        ]

    def _mic_dir(self, i, j):
        """Unit vector from atom i toward atom j across periodic images."""
        v = self.bond_image(i, j)
        n = np.linalg.norm(v)
        return v / n if n > 1e-10 else np.array([0.0, 0.0, 1.0])

    # ── Hydrogens ─────────────────────────────────────────────────────────

    def add_caps(self):
        """Cap every degree-1 backbone carbon with one H and rename it "C".

        Call BEFORE add_methylene_hydrogens()."""
        new_atoms = []

        for i in range(self._n):
            if (
                self._particles[i].name in self._CC_NAMES
                and len(self._neighbors[i]) == 1
            ):
                pos = self._positions[i].copy()
                direction = -self._mic_dir(i, self._neighbors[i][0])
                new_atoms.append((i, pos + direction * self._CH_BOND))
                self._particles[i].name = "C"

        self._grow(len(new_atoms))
        for bond_to, pos in new_atoms:
            self.add_bond(bond_to, self.add_particle("H_end", pos))

        print(f"[add_caps] +H on {len(new_atoms)} chain ends (terminus -> C)")
        return len(new_atoms)

    def add_methylene_hydrogens(self):
        """Add 2 H to every backbone carbon (H-C-H 109.5°).

        Call AFTER add_caps() and BEFORE to_mbuild()."""
        half = np.radians(54.75)
        cos_h, sin_h = np.cos(half), np.sin(half)

        targets = [
            i for i in range(self._n)
            if self._particles[i].name in self._CC_NAMES
        ]
        self._grow(2 * len(targets))

        n_added = 0
        for i in targets:
            pos = self._positions[i].copy()
            nbrs = self._neighbors[i]

            if nbrs:
                bond_dirs = [self._mic_dir(i, nb) for nb in nbrs]
                raw = -np.sum(bond_dirs, axis=0)
                nrm = np.linalg.norm(raw)
                bisector = raw / nrm if nrm > 1e-8 else np.array([0.0, 0.0, 1.0])
                ref_dir = bond_dirs[0]
            else:
                bisector = np.array([0.0, 0.0, 1.0])
                ref_dir = np.array([1.0, 0.0, 0.0])

            perp = np.cross(bisector, ref_dir)
            if np.linalg.norm(perp) < 1e-8:
                perp = np.cross(bisector, np.array([0.0, 1.0, 0.0]))
            nrm = np.linalg.norm(perp)
            if nrm > 1e-8:
                perp = perp / nrm

            for v in (cos_h * bisector + sin_h * perp,
                      cos_h * bisector - sin_h * perp):
                h_dir = v / np.linalg.norm(v)
                self.add_bond(
                    i, self.add_particle("H", pos + h_dir * self._CH_BOND)
                )
                n_added += 1

        print(
            f"[add_methylene_hydrogens] Checked {len(targets)} C atoms, "
            f"added {n_added} H atoms"
        )
        return n_added

    # ── Convert back to mBuild ────────────────────────────────────────────

    def to_mbuild(self, rename_to_elements=False):
        """Reconstruct an mBuild Compound from the current state."""
        import mbuild as mb

        pos_nm = self._positions / 10.0
        unknown = set()

        gc.disable()  # skip gen2 GC traversals while creating ~N objects
        try:
            mb_particles = []
            for i in range(self._n):
                name = self._particles[i].name
                element = self._ELEMENT_MAP.get(name)
                if element is None:
                    unknown.add(name)
                mb_particles.append(
                    mb.Compound(name=name, pos=pos_nm[i], element=element)
                )

            compound = mb.Compound()
            compound.add(mb_particles)  # one add() -> mBuild's batch path

            n_bonds = 0
            add_bond = compound.add_bond
            for i in range(self._n):
                for j in self._neighbors[i]:
                    if i < j:
                        add_bond((mb_particles[i], mb_particles[j]), bond_order=None)
                        n_bonds += 1
        finally:
            gc.enable()

        if unknown:
            print(
                f"[to_mbuild] WARNING: no element mapping for names: "
                f"{sorted(unknown)}. Add them to _ELEMENT_MAP."
            )

        if rename_to_elements:
            for p in compound.particles():
                el = self._ELEMENT_MAP.get(p.name)
                if el is not None:
                    p.name = el

        print(f"[to_mbuild] {self._n} atoms, {n_bonds} bonds -> mb.Compound")
        return compound

In [52]:
# ── Unit conversions ──────────────────────────────────────────────────────
BOX_Å       = np.array([LX * 10, LY * 10, LZ * 10])
z_amor_lo_Å = z_amor_lo * 10
z_amor_hi_Å = z_amor_hi * 10

# ── Build MDSystem AFTER cuts ─────────────────────────────────────────────
md_sys = MDSystem(system, BOX_Å)

# ── Classify atoms ────────────────────────────────────────────────────────
crystal_idx = set(
    i for i in range(md_sys._n)
    if md_sys[i][2] < z_amor_lo_Å or md_sys[i][2] > z_amor_hi_Å
)
amorphous_idx = [i for i in range(md_sys._n) if i not in crystal_idx]

lower_roots, upper_roots = [], []
for i in crystal_idx:
    if any(nb not in crystal_idx for nb in md_sys.bonded_neighbors(i)):
        if md_sys[i][2] < z_amor_lo_Å:
            lower_roots.append(i)
        else:
            upper_roots.append(i)

print(f"Crystal atoms  : {len(crystal_idx)}")
print(f"Amorphous atoms: {len(amorphous_idx)}")
print(f"Lower roots    : {len(lower_roots)}")
print(f"Upper roots    : {len(upper_roots)}")

# ── Diagnostic ────────────────────────────────────────────────────────────
all_ends  = md_sys.end_atoms()
amor_ends = [e for e in all_ends if e in set(amorphous_idx)]
print(f"True chain ends    : {len(all_ends)}")
print(f"Amorphous ends     : {len(amor_ends)}")

# ── Build MC object ───────────────────────────────────────────────────────
mc = MonteCarlo(
    system               = md_sys,
    upper_root_atoms     = upper_roots,
    lower_root_atoms     = lower_roots,
    amorphous_atoms      = amorphous_idx,
    search_radius        = 10.0,
    length_factor        = 1.0,
    crystal_buffer_depth = 2,
)

mc.count_segments("segments_init.txt")

# In run_mc.py — replace the Phase 1 loop
N_CYCLES    = 10000
MAX_FAIL    = 200     # give up after this many consecutive failures
accepted    = attempted = consecutive_fails = 0
print("\n── Phase 1: equilibration ──")
for cycle in range(N_CYCLES):
    attempted += 1
    
    if random.random() < 0.5:          # ← add this
        result = mc.end_bridge()
    else:
        result = mc.tail_reconnect()   # ← add this
    
    if result:                         # ← was: if mc.end_bridge()
        accepted          += 1
        consecutive_fails  = 0
    else:
        consecutive_fails += 1
    if consecutive_fails >= MAX_FAIL:
        print(f"\n!! MC stuck after {consecutive_fails} consecutive "
              f"failures at cycle {cycle} — stopping early")
        break
    if cycle % 100 == 0:
        _, _, tails = mc.count_segments(f"segments_{cycle:05d}.txt")
        print(f"  Cycle {cycle:5d}  accepted={accepted}/{attempted}")
print(f"\n── Phase 1 done: {accepted}/{attempted} ──")

# mc.connect_to_n_chains(n=2, T=450.0)
# mc.count_segments()

T, T_DELTA = 10_000.0, (450.0 - 10_000.0) / N_CYCLES
accepted = attempted = 0
print("\n── Phase 2: ramp 10000→450 K ──") # accept moves based on exp(-ΔE/kT)
for cycle in range(N_CYCLES):
    attempted += 1
    
    if random.random() < 0.5:          # ← add this
        result = mc.end_bridge(T=T)
    else:
        result = mc.tail_reconnect(T=T)   # ← add this
    
    if result:                         # ← was: if mc.end_bridge()
        accepted += 1
    T += T_DELTA
    if cycle % 500 == 0:
        print(f"  Cycle {cycle:5d}  T={T:.1f} K  accepted={accepted}/{attempted}")
print(f"\n── Phase 2 done: {accepted}/{attempted} ──")

_, _, tails = mc.count_segments(f"segments_final_5.txt")

Crystal atoms  : 19740
Amorphous atoms: 8400
Lower roots    : 140
Upper roots    : 140
True chain ends    : 280
Amorphous ends     : 280
  Total chains : 140
  |- Bridges   : 0
  |- Loops     : 0
  '- Broken    : 140  (280 tail segments)
  Stems        : 140   Roots : 280
  f_tie        : 0.0000 per chain   (theory n_stem = 1)

── Phase 1: equilibration ──
  Total chains : 140
  |- Bridges   : 1
  |- Loops     : 0
  '- Broken    : 139  (278 tail segments)
  Stems        : 140   Roots : 280
  f_tie        : 0.0036 per chain   (theory n_stem = 1)
  Cycle     0  accepted=1/1
  Total chains : 140
  |- Bridges   : 26
  |- Loops     : 33
  '- Broken    : 81  (162 tail segments)
  Stems        : 140   Roots : 280
  f_tie        : 0.1176 per chain   (theory n_stem = 2)
  Cycle   100  accepted=101/101
  Total chains : 140
  |- Bridges   : 54
  |- Loops     : 55
  '- Broken    : 31  (62 tail segments)
  Stems        : 140   Roots : 280
  f_tie        : 0.3158 per chain   (theory n_stem = 5)
  Cy

In [ ]:
md_sys.add_caps() #add 1H to each C/C_e
md_sys.add_methylene_hydrogens()   # adds 2H to each C/C_e``````

[add_caps] +H on 4 chain ends (terminus -> C)
[add_methylene_hydrogens] Checked 28140 C atoms, added 56280 H atoms


56280

In [54]:
# ── Rebuild mBuild Compound and save ─────────────────────────────────────
rebuilt = md_sys.to_mbuild(rename_to_elements=True)
box_nm  = mb.Box([LX, LY, LZ])          # Å → nm for mBuild


[to_mbuild] 84424 atoms, 84422 bonds -> mb.Compound


In [55]:
rebuilt.visualize(show_ports=False)

3Dmol.js failed to load for some reason. Please check your browser console for error messages.

In [57]:
from gmso.core.forcefield import ForceField
import foyer
import forcefield_utilities as ffutils
from mbuild.lib.molecules import Ethane
from gmso.external.convert_mbuild import from_mbuild
from gmso.parameterization import apply
from gmso.formats.lammpsdata import write_lammpsdata

chain_top = rebuilt.to_gmso()

gaff = ForceField("oplsaa.xml")
apply(
    top=chain_top,
    forcefields=gaff,
    identify_connections=True,
    remove_untyped=False)

<Topology Topology, 84424 sites,
 619064 connections,
 590928 potentials,
 id: 17037829088>

In [58]:
chain_top._impropers.clear()          # O(1), replaces the whole loop

write_lammpsdata(
    chain_top,
    filename=f'pE_2_chain_mc_201miller.data',
    atom_style='full',
    unit_style='real',
    strict_potentials=False,  # bypasses the expression check
)

In [59]:
#!/usr/bin/env python3
"""
gen_vmd.py  —  Generate a VMD TCL visualisation script from segments.txt

Cap atoms (OH_end, HO_end) added after segment classification are included
by a 2-hop BFS from each segment's heavy atoms using the LAMMPS bond graph.

Usage:
    python gen_vmd.py segments.txt pga_mc_test.data [output.tcl]
"""


# ── Representation settings ───────────────────────────────────────────────────
VDW_REP  = "VDW 0.30 12"
BOND_REP = "Bonds 0.15 12"

# ── LAMMPS data file parser ───────────────────────────────────────────────────

def parse_lammps(data_path):
    """Return bonds dict: atom_id → set of bonded atom_ids  (1-based)."""
    bonds   = {}
    section = None

    with open(data_path) as f:
        for raw in f:
            line = raw.strip()
            if not line or line.startswith("#"):
                continue

            # Detect section headers (may have trailing comments)
            head = line.split("#")[0].strip()
            if head in ("Masses", "Atoms", "Bonds", "Angles",
                        "Dihedrals", "Impropers",
                        "Pair Coeffs", "Bond Coeffs",
                        "Angle Coeffs", "Dihedral Coeffs",
                        "Improper Coeffs"):
                section = head
                continue
            if re.match(r'^\d+ (atoms|bonds|angles|dihedrals|impropers|'
                        r'atom types|bond types|angle types|'
                        r'dihedral types|improper types)', head):
                continue
            if re.search(r'xlo|ylo|zlo', head):
                continue

            if section == "Atoms":
                parts = line.split()
                if len(parts) >= 2:
                    try:
                        aid = int(parts[0])
                        bonds.setdefault(aid, set())
                    except ValueError:
                        pass

            elif section == "Bonds":
                parts = line.split()
                if len(parts) >= 4:
                    try:
                        a1 = int(parts[2])
                        a2 = int(parts[3])
                        bonds.setdefault(a1, set()).add(a2)
                        bonds.setdefault(a2, set()).add(a1)
                    except ValueError:
                        pass

    return bonds

# ── Segment extension ─────────────────────────────────────────────────────────

def extend_segment(seg_set, bonds, all_heavy_atoms, max_hops=2):
    """
    BFS up to max_hops from the segment's heavy atoms.
    Adds atoms that are NOT heavy atoms of any OTHER segment
    (i.e. cap atoms: OH_end, HO_end, HO_start, and their H).

    all_heavy_atoms = union of all segment heavy-atom IDs.
    An atom can be added if it is not in all_heavy_atoms,
    or if it IS in all_heavy_atoms but in this segment (self-loop guard).
    """
    result   = set(seg_set)
    frontier = set(seg_set)

    for _ in range(max_hops):
        new_frontier = set()
        for aid in frontier:
            for nb in bonds.get(aid, set()):
                if nb in result:
                    continue
                # Accept if it's a cap atom (not a heavy atom of any segment)
                # OR if it belongs to THIS segment's heavy atoms (already included)
                if nb not in all_heavy_atoms:
                    result.add(nb)
                    new_frontier.add(nb)
        frontier = new_frontier
        if not frontier:
            break

    return result

# ── Segments parser ───────────────────────────────────────────────────────────

def parse_segments(path):
    tails, bridges, loops = [], [], []
    current = None
    with open(path) as f:
        for line in f:
            line = line.strip()
            if   line.startswith("Tails"):   current = tails
            elif line.startswith("Bridges"): current = bridges
            elif line.startswith("Loops"):   current = loops
            elif line.startswith("{") and current is not None:
                nums = list(map(int, re.findall(r'\d+', line)))
                if nums:
                    current.append(set(nums))
    return tails, bridges, loops

# ── Helpers ───────────────────────────────────────────────────────────────────

def serial_str(s):
    return " ".join(str(x) for x in sorted(s))

# ── TCL block ─────────────────────────────────────────────────────────────────

def seg_block(lines, seg_ext, color_id, label, var_name):
    lines.append(f'set {var_name} "serial {serial_str(seg_ext)}"')
    for rep, suffix in [(VDW_REP, "atoms"), (BOND_REP, "bonds")]:
        lines.append(f"mol representation {rep}")
        lines.append(f"mol color ColorID {color_id}")
        lines.append(f'mol selection "${var_name}"')
        lines.append(f"mol addrep $mol   ;# {label} – {suffix}")
    lines.append("")

# ── TCL generator ─────────────────────────────────────────────────────────────

def generate_tcl(tails, bridges, loops, data_file, out_path, bonds):

    # All heavy atom IDs across every segment
    all_heavy = set()
    for seg in tails + bridges + loops:
        all_heavy |= seg

    # Extend each segment with cap atoms via 2-hop BFS
    tails_ext   = [extend_segment(s, bonds, all_heavy) for s in tails]
    bridges_ext = [extend_segment(s, bonds, all_heavy) for s in bridges]
    loops_ext   = [extend_segment(s, bonds, all_heavy) for s in loops]

    # All amorphous atoms (heavy + caps)
    all_amor = set()
    for seg in tails_ext + bridges_ext + loops_ext:
        all_amor |= seg

    n_caps = len(all_amor) - len(all_heavy)
    print(f"  Cap atoms captured by 2-hop BFS: {n_caps}")

    n_t = len(tails_ext)
    n_b = len(bridges_ext)
    n_l = len(loops_ext)
    n_amor_total = sum(len(s) for s in tails_ext + bridges_ext + loops_ext)

    lines = []
    w = lines.append

    w("# ─────────────────────────────────────────────────────────────────────")
    w(f"# PGA segment visualisation — {Path(out_path).name}")
    w(f"#   Source data : {data_file}")
    w(f"#   Segments : {n_t} tails | {n_b} bridges | {n_l} loops")
    w(f"#   Cap atoms included via 2-hop bond BFS: {n_caps}")
    w("#   Crystal → white (8) | Tails → red (1) | Bridges → green (7) | Loops → blue (0)")
    w(f"# Usage:  vmd -lammpsdata {data_file} full -e {Path(out_path).name}")
    w("# ─────────────────────────────────────────────────────────────────────")
    w("")
    w("if {[molinfo num] == 0} {")
    w(f'    topo readlammpsdata {data_file} full')
    w("}")
    w("set mol [molinfo top]")
    w("mol delrep 0 $mol")
    w("")

    # Crystal = everything NOT in any extended amorphous segment
    amor_str = serial_str(all_amor)
    w("# ── CRYSTALLINE – white ──────────────────────────────────────────────")
    w(f'set amor_all "serial {amor_str}"')
    crystal_sel = "not ($amor_all)"
    for rep, suffix in [(VDW_REP, "atoms"), (BOND_REP, "bonds")]:
        w(f"mol representation {rep}")
        w( "mol color ColorID 8")
        w(f'mol selection "{crystal_sel}"')
        w(f"mol addrep $mol   ;# crystal – {suffix}")
    w("")

    w("# ── TAILS – red ──────────────────────────────────────────────────────")
    for i, seg in enumerate(tails_ext, 1):
        seg_block(lines, seg, 1, f"tail {i}", f"t{i}")

    w("# ── BRIDGES – green ──────────────────────────────────────────────────")
    for i, seg in enumerate(bridges_ext, 1):
        seg_block(lines, seg, 7, f"bridge {i}", f"b{i}")

    w("# ── LOOPS – blue ─────────────────────────────────────────────────────")
    for i, seg in enumerate(loops_ext, 1):
        seg_block(lines, seg, 0, f"loop {i}", f"l{i}")

    w("# ── Display ──────────────────────────────────────────────────────────")
    w("display projection orthographic")
    w("display depthcue off")
    w("axes location off")
    w("color Display Background black")
    w("")
    w('puts "=== Segment counts (caps included) ==="')
    w(f'puts "  Amorphous atoms (incl. caps) : {n_amor_total}"')
    w(f'puts "  Tails: {n_t} | Bridges: {n_b} | Loops: {n_l}"')
    w('puts "  White=crystal | Red=tails | Green=bridges | Blue=loops"')

    with open(out_path, "w") as f:
        f.write("\n".join(lines) + "\n")

    print(f"Written : {out_path}")
    print(f"  {n_t} tails | {n_b} bridges | {n_l} loops")
    print(f"  Total amorphous atoms (incl. caps): {n_amor_total}")

def main():

    seg_file  = 'segments_final_5.txt'
    data_file = f'pE_2_chain_mc_201miller.data'
    out_file  = f"{data_file}_vis_2.tcl"

    print(f"Parsing segments : {seg_file}")
    tails, bridges, loops = parse_segments(seg_file)
    print(f"  {len(tails)} tails | {len(bridges)} bridges | {len(loops)} loops")

    print(f"Parsing LAMMPS bonds : {data_file}")
    bonds = parse_lammps(data_file)
    print(f"  {len(bonds)} atoms, {sum(len(v) for v in bonds.values())//2} bonds")

    generate_tcl(tails, bridges, loops, data_file, out_file, bonds)



main()

Parsing segments : segments_final_5.txt
  4 tails | 14 bridges | 124 loops
Parsing LAMMPS bonds : pE_2_chain_mc_201miller.data
  84424 atoms, 84422 bonds
  Cap atoms captured by 2-hop BFS: 18484
Written : pE_2_chain_mc_201miller.data_vis_2.tcl
  4 tails | 14 bridges | 124 loops
  Total amorphous atoms (incl. caps): 27164
